Import libraries for data cleaning 

In [1]:
import csv
from tokenize import String

from notebooks.mongoDB_connection import get_mongo_db
from notebooks.db_connection import execute_query
import numpy as np
import pandas as pd
import os
import re
import pandas.io.sql as psql
import psycopg2 as ps

Connection Successful!


Reading CSV file

In [2]:
df_reviews = pd.read_csv(r"C:\Users\aless\Desktop\Uni\Dataset\rotten_tomatoes_reviews.csv\rotten_tomatoes_reviews.csv")

Top records of CSV file: rotten_tomatoes_reviews.csv

In [3]:
df_reviews

,rotten_tomatoes_link,movie_title,critic_name,top_critic,publisher_name,review_type,review_score,review_date,review_content
0,m/0814255,Percy Jackson & the Olympians: The Lightning T...,Andrew L. Urban,False,Urban Cinefile,Fresh,NaN,2010-02-06,A fantasy adventure that fuses Greek mythology...
1,m/0814255,Percy Jackson & the Olympians: The Lightning T...,Louise Keller,False,Urban Cinefile,Fresh,NaN,2010-02-06,"Uma Thurman as Medusa, the gorgon with a coiff..."
2,m/0814255,Percy Jackson & the Olympians: The Lightning T...,NaN,False,FILMINK (Australia),Fresh,NaN,2010-02-09,With a top-notch cast and dazzling special eff...
3,m/0814255,Percy Jackson & the Olympians: The Lightning T...,Ben McEachen,False,Sunday Mail (Australia),Fresh,3.5/5,2010-02-09,Whether audiences will get behind The Lightnin...
4,m/0814255,Percy Jackson & the Olympians: The Lightning T...,Ethan Alter,True,Hollywood Reporter,Rotten,NaN,2010-02-10,What's really lacking in The Lightning Thief i...
...,...,...,...,...,...,...,...,...,...
1129882,m/zulu_dawn,Zulu Dawn,Chuck O'Leary,False,Fantastica Daily,Rotten,2/5,2005-11-02,NaN
1129883,m/zulu_dawn,Zulu Dawn,Ken Hanke,False,"Mountain Xpress (Asheville, NC)",Fresh,3.5/5,2007-03-07,"Seen today, it's not only a startling indictme..."
1129884,m/zulu_dawn,Zulu Dawn,Dennis Schwartz,False,Dennis Schwartz Movie Reviews,Fresh,B+,2010-09-16,A rousing visual spectacle that's a prequel of...
1129885,m/zulu_dawn,Zulu Dawn,Christopher Lloyd,False,Sarasota Herald-Tribune,Rotten,3.5/5,2011-02-28,"A simple two-act story: Prelude to war, and th..."


Checking for total dimension of the csv

In [4]:
df_reviews.shape

(1129887, 9)

In [5]:
df_reviews.columns

Index(['rotten_tomatoes_link', 'movie_title', 'critic_name', 'top_critic',
       'publisher_name', 'review_type', 'review_score', 'review_date',
       'review_content'],
      dtype='object')

Check info about column type

In [6]:
df_reviews.dtypes

rotten_tomatoes_link    object
movie_title             object
critic_name             object
top_critic                bool
publisher_name          object
review_type             object
review_score            object
review_date             object
review_content          object
dtype: object

Correction of data type of the records. Keeping review_score as an object to preserve original formats.

In [7]:
df_reviews['rotten_tomatoes_link'] = df_reviews['rotten_tomatoes_link'].astype('string')
df_reviews['movie_title'] = df_reviews['movie_title'].astype('string')
df_reviews['critic_name'] = df_reviews['critic_name'].astype('string')
df_reviews['top_critic'] = df_reviews['top_critic'].fillna(pd.NA).astype('bool')
df_reviews['publisher_name'] = df_reviews['publisher_name'].fillna(pd.NA).astype('string')
df_reviews['review_type'] = df_reviews['review_type'].fillna(pd.NA).astype('string')
df_reviews["review_date"] = pd.to_datetime(df_reviews["review_date"], errors="coerce")
df_reviews['review_content'] = df_reviews['review_content'].fillna(pd.NA).astype('string')

Check if there are duplicates

In [8]:
df_reviews.duplicated().sum()


np.int64(119471)

Dropping duplicates

In [9]:
df_reviews.drop_duplicates(inplace = True)
df_reviews.duplicated().sum()

np.int64(0)

Check the missing values

In [10]:
df_reviews.isnull().sum()

rotten_tomatoes_link         0
movie_title                  0
critic_name              16446
top_critic                   0
publisher_name               0
review_type                  0
review_score            273571
review_date                  0
review_content           58498
dtype: int64

Dropping records with missing value 

In [11]:
df_reviews.dropna(subset=["movie_title", 'review_type', 'review_content'], inplace=True)
df_reviews.isnull().sum()

rotten_tomatoes_link         0
movie_title                  0
critic_name               8894
top_critic                   0
publisher_name               0
review_type                  0
review_score            273182
review_date                  0
review_content               0
dtype: int64

In [12]:
df_reviews.shape

(951918, 9)

Connecting to MongoDB database

In [13]:
db = get_mongo_db()
collection = db['reviews']

MongoDB connection established!


Convert the dataframe in MongoDB format

In [14]:
df_reviews = df_reviews.to_dict(orient = 'records')

Population of the table reviews in mongoDB

In [15]:
collection.insert_many(df_reviews)

InsertManyResult([ObjectId('68b0bc36d228aa360db580b4'), ObjectId('68b0bc36d228aa360db580b5'), ObjectId('68b0bc36d228aa360db580b6'), ObjectId('68b0bc36d228aa360db580b7'), ObjectId('68b0bc36d228aa360db580b8'), ObjectId('68b0bc36d228aa360db580b9'), ObjectId('68b0bc36d228aa360db580ba'), ObjectId('68b0bc36d228aa360db580bb'), ObjectId('68b0bc36d228aa360db580bc'), ObjectId('68b0bc36d228aa360db580bd'), ObjectId('68b0bc36d228aa360db580be'), ObjectId('68b0bc36d228aa360db580bf'), ObjectId('68b0bc36d228aa360db580c0'), ObjectId('68b0bc36d228aa360db580c1'), ObjectId('68b0bc36d228aa360db580c2'), ObjectId('68b0bc36d228aa360db580c3'), ObjectId('68b0bc36d228aa360db580c4'), ObjectId('68b0bc36d228aa360db580c5'), ObjectId('68b0bc36d228aa360db580c6'), ObjectId('68b0bc36d228aa360db580c7'), ObjectId('68b0bc36d228aa360db580c8'), ObjectId('68b0bc36d228aa360db580c9'), ObjectId('68b0bc36d228aa360db580ca'), ObjectId('68b0bc36d228aa360db580cb'), ObjectId('68b0bc36d228aa360db580cc'), ObjectId('68b0bc36d228aa360db580